# Solving bubble dynamics with the Gilmore-Akulichev model

This notebook provides an example for simulating bubble dynamics and calculating the radiated pressure using the BubbleDynamics class.

In [1]:
import sys
from plotly import graph_objects as go

sys.path.append("..")
from wavelet_transform.utils.viscoelasticbd import vsbd as BD
import numpy as np
import plotly.express as px
from IPython.display import display
from wavelet_transform.utils.save_plots import save_figure

import wavelet_transform.utils.statistical_features as st
import scipy.signal as ss

Define the sonication parameters and the initial bubble radius and velocity. By default, we consider a vapour bubble in an unbounded aqueous medium at room temperature (20 C). The sonication signal is considered to be a monotone signal as follows: $~p_{ac} \times sin(2 \pi f t)$. 

In [2]:
fs = 1e10  # sampling rate to generate the time vector

savefigs_flag = False
plotly_figs = True if fs < 1.1e11 else False
fontsize = 30
margin = dict(l=50, r=0, t=60, b=120)

In [3]:
f0_frequency = 6 * 1e6  # 0.4:10 MHz insonation frequency (Hz)
mi = 0.3  # mechanical index, MI = P_neg / sqrt(frequency), where P_neg is the negative pressure in MPa and frequency is in MHz
pac = mi * np.sqrt(f0_frequency / 1e6) * 1.e6  # the amplitude of the sine wave in Pa
print(f"pac = {pac:.2e} Pa")
period = 1 / f0_frequency # the period of the acoustic wave at the fundamental frequency 
no_cycle = 3  # no. of cycles of the sine wave

time_delay = no_cycle * period  # 4 * period  # time delay, t1
n_std = 2  # number of standard deviations for pulse width. e.g. 2 stds will give n_cycles of sine wave which make up 95% of the envelope energy
pulse_width = 1 / (2 * n_std) * (no_cycle) * period  # pulse width
time_initial = time_delay  # sync pulse with time delay of window
phase_shift = 0  # np.pi / 4  # phi
no_harmonics = 1  # k

r_measure = 10e-3  # distance from the centre of bubble which radiated pressure 
                   # (acoustic emission from bubble) is calculated over time
c = 1540  # speed of sound in the medium (m/s) for calculating time delay for 2nd pulse

deltat = 1.0 / fs
tmax = time_delay + 4 * r_measure / c  # total time for bd [s]
time = np.arange(
    0.0, tmax, deltat
)  # time vector for computing the sine wave, in seconds

R_init = 2e-6  # initial bubble radius in meters [0.2, 0.84, 3] @ 6 MHz
Rdot_init = 0  # initial bubble's wall velocity in m/s

pac = 7.35e+05 Pa


parameters for secondary pulse

In [4]:
f0_frequency_1 = f0_frequency  # 0.4:10 MHz insonation frequency (Hz)
pac_1 = .5 * pac  # set to equal -pac for pulse inv. any other number for amp mod, set to 0 for 2nd harmonic
time_delay_1 = time_delay + 2 * r_measure / c  # delay by 2-way travel time
pulse_width_1 = pulse_width
if pac_1 == pac:
    print("pulse inversion applied: pac_1 = -pac")
    req_shift = np.pi
else:
    req_shift = 0
time_initial_1 = time_delay_1
phase_shift_1 = phase_shift - req_shift
no_harmonics_1 = no_harmonics

Setting up the bubble dynamics object for the above parameters.

In [5]:
BD_obj = BD(
    R_init=R_init,
    Rdot_init = Rdot_init,
    frequency = f0_frequency,
    time = time,
    deltat = deltat,
)

BD_obj.medium_parameters["G"] = 1e3  # set to 200 kPa for gel. 0 kPa for water.
BD_obj.nd_params["kappa_s"] = 0e-9  # set to 6e-9 for coated bubbles, 0 for uncoated

In [6]:
window = "tanh"  # "gaussian" or "tanh". 

if window == "gaussian":
    BD_obj.add_pac_wave(
        f0_frequency, 
        pac, 
        time_delay, 
        pulse_width, 
        time_initial, 
        phase_shift, 
        no_harmonics
    )

    BD_obj.add_pac_wave(
        f0_frequency_1, 
        pac_1, 
        time_delay_1, 
        pulse_width_1, 
        time_initial_1, 
        phase_shift_1, 
        no_harmonics_1
    )
elif window == "tanh":
    BD_obj.add_tanh_wave(
        f0_frequency,
        pac,
        time_delay,
        no_cycle,
        n_cycles_taper=no_cycle / 3,
        phase_shift=phase_shift + np.pi
    )

    BD_obj.add_tanh_wave(
        f0_frequency_1,
        pac_1,
        time_delay_1,
        no_cycle,
        n_cycles_taper=no_cycle / 3,
        phase_shift=phase_shift_1 + np.pi
    )

In [7]:
# print("The resonance frequency of this bubble is: {0:.4f} MHz,\nIt is {1:.4f} times of the excitation frequency.".format(
#     BD_obj.resonance_frequency * 1e-6, BD_obj.resonance_frequency/f0_frequency))

In [8]:
# print("The resonance period of this bubble is: {0:.4f} times of the excitation period".format(1/BD_obj.resonance_frequency / period))

In [9]:
if plotly_figs:
    fig = go.Figure()
    fig.add_trace(
        go.Scatter(
            x=BD_obj.time.copy() / period, y=BD_obj.pac_wave.copy() / 1e6
        )
    )
    fig.update_layout(
        font_family="Arial",
        xaxis=dict(title="time [t/T]"),
        yaxis=dict(title="Pressure [MPa]"),
        # title="Incident sound wave",
        font_size=fontsize,
        plot_bgcolor="white",
    )
    fig.update_xaxes(
        mirror=True,
        ticks="outside",
        showline=True,
        linecolor="black",
        gridcolor="lightgrey",
    )
    fig.update_yaxes(
        mirror=True,
        ticks="outside",
        showline=True,
        linecolor="black",
        gridcolor="lightgrey",
    )
    fig.show()
else: 
    import matplotlib.pyplot as plt
    plt.plot(BD_obj.time, BD_obj.pac_wave)
    plt.xlabel("Time [s]")
    plt.ylabel("Pressure [Pa]")
    plt.title("Incident Sound Wave")
    plt.show()

Solve the bubble dynamics modelled by the nonlinear Gilmore ordinary differential equation

In [10]:
BD_obj.solver()

Visualise the results:

In [11]:
if plotly_figs:
    fig = go.Figure()
    fig.add_trace(
        go.Scatter(
                x=BD_obj.time.copy() / period,
                y=BD_obj.R / R_init,
            )
        )
    fig.update_layout(
        xaxis=dict(title="time [t/T]"),
        yaxis=dict(title="R / R<sub>0</sub>"), 
        font_size=fontsize,
        # title="Bubble radius vs time",
        plot_bgcolor="white",
    )
    fig.update_xaxes(
        mirror=True,
        ticks="outside",
        showline=True,
        linecolor="black",
        gridcolor="lightgrey",
    )
    fig.update_yaxes(
        mirror=True,
        ticks="outside",
        showline=True,
        linecolor="black",
        gridcolor="lightgrey",
    )
    fig.show()

    r_init_plot = f"{R_init*1e6:.1f}".replace(".", "p")

    if savefigs_flag is True:
        save_figure(fig, f"r_{r_init_plot}", r"./ga_results", margin=margin)
else:
    plt.plot(BD_obj.time, BD_obj.R)
    plt.xlabel("Time [s]")
    plt.ylabel("Bubble radius [m]")
    plt.title("Bubble radius vs time")
    plt.show()

In [12]:
if plotly_figs:
    fig = go.Figure()
    fig.add_trace(
        go.Scatter(
            x=BD_obj.time/period, 
            y=BD_obj.Rdot / (R_init * 2 * np.pi * f0_frequency)
        )
    )
    fig.update_layout(
        # font_family="'Serif",
        xaxis=dict(title="time [t/T]"),
        yaxis=dict(title="<span>&#7768;</span> / R<sub>0</sub> &#969;"),
        # title="Bubble radius velocity vs time",
        font_size=fontsize,
        plot_bgcolor="white",
    )
    fig.update_xaxes(
        mirror=True,
        ticks="outside",
        showline=True,
        linecolor="black",
        gridcolor="lightgrey",
    )
    fig.update_yaxes(
        mirror=True,
        ticks="outside",
        showline=True,
        linecolor="black",
        gridcolor="lightgrey",
    )
    fig.show()

    if savefigs_flag is True:
        save_figure(fig, f"rdot_{r_init_plot}", r"./ga_results", margin=margin)
else:
    plt.plot(BD_obj.time, BD_obj.Rdot)
    plt.xlabel("Time [s]")
    plt.ylabel("Bubble wall velocity [m/s]")
    plt.title("Bubble radius velocity vs time")
    plt.show()

# The HTML coding is used for greek letters and sub/superscripts and overdots in the labels. 
# The list of unicodes of letters can be found here: https://www.compart.com/en/unicode/U+03C9

Now, we can calculate the emitted acoustic wave (measured irradiated pressure) from this oscillating bubble at a distance `r_measure` from the centre of the bubble, as follows

In [13]:
BD_obj.calculate_p_radiated(r_measure=r_measure)

In [14]:
if plotly_figs:
    # plot result
    fig = go.Figure()
    fig.add_trace(
        go.Scatter(
            x=BD_obj.time/period,
            y=BD_obj.p_radiated / BD_obj.medium_parameters["p0"],
        )
    )
    fig.update_layout(
        font_family="Arial",
        xaxis=dict(title="time [t/T]"),
        yaxis=dict(title="P<sub>rad</sub> / P<sub>0</sub>"),
        plot_bgcolor="white",
        font_size=fontsize
    )

    fig.update_xaxes(
        mirror=True,
        ticks="outside",
        showline=True,
        linecolor="black",
        gridcolor="lightgrey",
    )
    fig.update_yaxes(
        mirror=True,
        ticks="outside",
        showline=True,
        linecolor="black",
        gridcolor="lightgrey",
    )

    if savefigs_flag is True:
        save_figure(fig, f"p_{r_init_plot}", r"./ga_results", margin=margin)

    fig.show()

subtract radiated pressure waves

In [15]:
timeframe = no_cycle * period * 2  # timeframe to plot n * period * pad
rel_delay = time_delay_1 - time_delay  # delay between pulses
t_cutoff = [
    time_delay, 
    time_delay + timeframe, 
    time_delay + rel_delay, 
    time_delay + rel_delay + timeframe
]

# factor of 1.2 to include some of the waveform before the main pulse.
t_cutoff = [i - no_cycle * period / 2 * 1.5 for i in t_cutoff]

p_rad_0 = BD_obj.p_radiated.copy() - 1  # centre waveform around r_0
p_rad_0 = p_rad_0[(BD_obj.time > t_cutoff[0]) & (BD_obj.time <= (t_cutoff[1]))]

p_rad_1 = BD_obj.p_radiated.copy() - 1  # centre waveform around r_0
p_rad_1 = p_rad_1[(BD_obj.time > t_cutoff[2]) & (BD_obj.time <= (t_cutoff[3]))]

In [16]:
p_rad_0.size, p_rad_1.size

(10000, 10000)

plot pressure waves

In [17]:
figure = go.Figure()
figure.add_trace(
    go.Scatter(
        x=BD_obj.time[:len(p_rad_0)] / period,
        y=p_rad_0 / BD_obj.medium_parameters["p0"],
        name="P1"
    )
)
if pac_1 != 0:
    figure.add_trace(
        go.Scatter(
            x=BD_obj.time[:len(p_rad_1)] / period,
            y=p_rad_1 / BD_obj.medium_parameters["p0"],
            name="P2"
        )
    )

if pac_1 == 0:  # if pac_1 is 0, assume 2nd harmonic imaging
    f = ss.butter(4, [f0_frequency*1.5, f0_frequency*2.5], btype="bandpass", fs=fs)
    contrast_signal = ss.filtfilt(*f, p_rad_0)
    figure.add_trace(
        go.Scatter(
            x=BD_obj.time[:len(contrast_signal)] / period,
            y=contrast_signal / BD_obj.medium_parameters["p0"],
            name="2nd harmonic"
        )
    )
else: 
    if pac_1 == pac:  # assume pulse inversion
        contrast_signal = p_rad_0 + p_rad_1
        figure.add_trace(
            go.Scatter(
                x=BD_obj.time[:len(p_rad_0)] / period,
                y=contrast_signal / BD_obj.medium_parameters["p0"],
                name="PI"
            )
        )
    else:  # assume amp mod if pac_1 != pac and pac_1 != 0
        contrast_signal = p_rad_0 - p_rad_1 * pac / pac_1
        figure.add_trace(
            go.Scatter(
                x=BD_obj.time[:len(p_rad_0)] / period,
                y=contrast_signal / BD_obj.medium_parameters["p0"],
                name="AM"
            )
        )

figure.update_layout(
    xaxis=dict(title="time [t/T]"),
    yaxis=dict(title="P<sub>rad</sub> / P<sub>0</sub>"),
    font_size=fontsize,
    plot_bgcolor="white",
)
figure.update_xaxes(
    mirror=True,
    ticks="outside",
    showline=True,
    linecolor="black",
    gridcolor="lightgrey",
)
if max(BD_obj.time[:len(p_rad_0)] / period) < 10:
    figure.update_xaxes(
        dtick=1
    )
figure.update_yaxes(
    mirror=True,
    ticks="outside",
    showline=True,
    linecolor="black",
    gridcolor="lightgrey",
)
figure.show()

peak = max(abs(contrast_signal / BD_obj.medium_parameters["p0"]))
print("peak contrast amplitude [dimensionless]:", f"{peak:.2e}")

peak contrast amplitude [dimensionless]: 4.78e-04


calculate psd of radiated pressure

In [18]:
sig = ss.detrend(BD_obj.p_radiated).copy()

In [19]:
fft_amp_0, fft_freq_0 = st.psd(p_rad_0, sampling_rate=fs, fundamental_freq=f0_frequency)
fft_amp_1, fft_freq_1 = st.psd(p_rad_1, sampling_rate=fs, fundamental_freq=f0_frequency)
fft_amp_contrast, fft_freq_contrast = st.psd(contrast_signal, sampling_rate=fs, fundamental_freq=f0_frequency)

In [20]:
freq_lim = 5
freq_index = fft_freq_0 < freq_lim
fig_new = go.Figure()

fig_new.add_trace(
    go.Scatter(
        x=fft_freq_0[freq_index],
        y=10*np.log10(fft_amp_0[freq_index]),
        name="P1"
    )
)

fig_new.add_trace(
    go.Scatter(
        x=fft_freq_1[freq_index],
        y=10*np.log10(fft_amp_1[freq_index]),
        name="P2"
    )
)

fig_new.add_trace(
    go.Scatter(
        x=fft_freq_contrast[freq_index],
        y=10*np.log10(fft_amp_contrast[freq_index]),
        name="CS"
    )
)

# set lower bound of y-axis to exclude large negative values.
lower_bound = min(
    np.percentile(10*np.log10(fft_amp_0[freq_index]), 5), 
    np.percentile(10*np.log10(fft_amp_1[freq_index]), 5), 
    np.percentile(10*np.log10(fft_amp_contrast[freq_index]), 5)
) - 10

fig_new.update_layout(
    yaxis_range=[lower_bound, max(10*np.log10(fft_amp_0[freq_index]))+10],
    xaxis_range=[0, freq_lim],
    xaxis=dict(title="Freq [F/F<sub>0</sub>]"),
    yaxis=dict(title=r"PSD [dB]"), font_size=fontsize,
    plot_bgcolor="white",
)

fig_new.update_xaxes(
    mirror=True,
    ticks="outside",
    showline=True,
    linecolor="black",
    gridcolor="lightgrey",
)

fig_new.update_yaxes(
    mirror=True,
    ticks="outside",
    showline=True,
    linecolor="black",
    gridcolor="lightgrey",
)

fig_new.show()

if savefigs_flag is True:
    save_figure(fig_new, f"fft_{r_init_plot}", r"./ga_results", margin=margin)